#Adding OPENAI API Key

In [ ]:
import os
from openai import OpenAI
from google.colab import userdata

OPENAI_API_KEY = userdata.get('OPENAI_API_KEY')
client = OpenAI(api_key=OPENAI_API_KEY)

# Loading MaizeField Dataset

In [ ]:
import glob

dataset_path = "/content/raw_100k/FielGrwon_ZeaMays_RawPCD_100k"

ply_files = glob.glob(dataset_path + "/*.ply")

print("Total plants:", len(ply_files))

Total plants: 1045


# TOOLS

## 1. Dataset statistics tool

In [ ]:
def dataset_stats():
    return f"There are {len(ply_files)} maize plants in the dataset."

## 2. Visualize a plant tool

In [ ]:
import open3d as o3d
import numpy as np
import plotly.graph_objects as go
import random

def visualize_random_plant():

    file = random.choice(ply_files)

    pcd = o3d.io.read_point_cloud(file)

    points = np.asarray(pcd.points)
    colors = np.asarray(pcd.colors)

    fig = go.Figure(data=[
        go.Scatter3d(
            x=points[:,0],
            y=points[:,1],
            z=points[:,2],
            mode='markers',
            marker=dict(size=2, color=colors)
        )
    ])

    fig.show()

    return f"Visualized plant: {file}"

In [ ]:
tools = {
    "dataset_stats": dataset_stats,
    "visualize_random_plant": visualize_random_plant
}

# System Prompt

In [ ]:
SYSTEM_PROMPT = """
You are a ReAct agent analyzing a maize plant dataset.

You can reason and take actions using tools.

Available actions:
- dataset_stats
- visualize_random_plant

Follow this format exactly:

Thought: describe what you want to do
Action: tool_name

The environment will execute the action and return:

Observation: result_of_tool

You MUST NOT generate Observations yourself.

You will receive the Observation after the tool executes.

Repeat the cycle until you can answer.

Final Answer: answer to the user.
"""

# ReAct Agent

In [ ]:
import re

def react_agent(question):

    messages = [
        {"role": "system", "content": SYSTEM_PROMPT},
        {"role": "user", "content": question}
    ]

    MAX_STEPS = 6

    for step in range(MAX_STEPS):

        response = client.chat.completions.create(
            model="gpt-3.5-turbo",
            messages=messages
        )

        reply = response.choices[0].message.content
        print(reply)

        # stop condition
        if "Final Answer:" in reply:
            break

        # parse action
        action_match = re.search(r"Action:\s*(\w+)", reply)
        input_match = re.search(r"Action Input:\s*(.*)", reply)

        if action_match:

            action = action_match.group(1)

            tool_input = None
            if input_match:
                tool_input = input_match.group(1).strip()

            if action in tools:

                if tool_input:
                    result = tools[action](tool_input)
                else:
                    result = tools[action]()

                messages.append({"role": "assistant", "content": reply})

                messages.append({
                    "role": "user",
                    "content": f"Observation: {result}"
                })

            else:
                print("Unknown tool:", action)
                break

        else:
            print("No action detected.")
            break

# Q&A with Agent

In [ ]:
react_agent("How many plants are in the maize dataset?")

Thought: I need to find out the number of plants in the maize dataset.
Action: dataset_stats
Final Answer: There are 1045 maize plants in the dataset.


In [ ]:
react_agent("Show me a maize plant")

Thought: I will visualize a random maize plant from the dataset.
Action: visualize_random_plant


Final Answer: Here is a visualization of a maize plant from the dataset.


# Extending the agent with other tools

## 1. Load plant

In [ ]:
def load_plant(plant_name):

    file = dataset_path + "/" + plant_name

    pcd = o3d.io.read_point_cloud(file)

    return file, pcd

## 2. Compute height

In [ ]:
def compute_height(plant_name):

    file, pcd = load_plant(plant_name)

    points = np.asarray(pcd.points)

    height = points[:,2].max() - points[:,2].min()

    return f"Plant {plant_name} height: {height:.3f} meters"

## 3. Voxelize plant

In [ ]:
def voxelize_plant(plant_name):

    file, pcd = load_plant(plant_name)

    voxel_grid = o3d.geometry.VoxelGrid.create_from_point_cloud(
        pcd,
        voxel_size=0.02
    )

    voxels = voxel_grid.get_voxels()

    centers = []

    for v in voxels:
        center = voxel_grid.get_voxel_center_coordinate(v.grid_index)
        centers.append(center)

    centers = np.array(centers)

    fig = go.Figure(data=[
        go.Scatter3d(
            x=centers[:,0],
            y=centers[:,1],
            z=centers[:,2],
            mode='markers',
            marker=dict(size=4, color=centers[:,2], colorscale='Viridis')
        )
    ])

    fig.show()

    return f"Voxel grid visualized for {plant_name}"

## 4. Build graph

In [ ]:
def build_graph(plant_name):

    file, pcd = load_plant(plant_name)

    pcd = pcd.voxel_down_sample(voxel_size=0.01)

    points = np.asarray(pcd.points)
    colors = np.asarray(pcd.colors)

    tree = o3d.geometry.KDTreeFlann(pcd)

    edge_x, edge_y, edge_z = [], [], []

    k = 6

    for i in range(len(points)):

        _, idx, _ = tree.search_knn_vector_3d(points[i], k)

        for j in idx[1:]:

            p1 = points[i]
            p2 = points[j]

            edge_x += [p1[0], p2[0], None]
            edge_y += [p1[1], p2[1], None]
            edge_z += [p1[2], p2[2], None]

    edge_trace = go.Scatter3d(
        x=edge_x,
        y=edge_y,
        z=edge_z,
        mode='lines',
        line=dict(width=1, color='black')
    )

    node_trace = go.Scatter3d(
        x=points[:,0],
        y=points[:,1],
        z=points[:,2],
        mode='markers',
        marker=dict(size=3, color=colors)
    )

    fig = go.Figure(data=[edge_trace, node_trace])
    fig.show()

    return f"Graph built and visualized for {plant_name}"

## 5. Reconstruct mesh

In [ ]:
def reconstruct_mesh(plant_name):

    file, pcd = load_plant(plant_name)

    pcd.estimate_normals(
        search_param=o3d.geometry.KDTreeSearchParamHybrid(
            radius=0.05,
            max_nn=50
        )
    )

    distances = pcd.compute_nearest_neighbor_distance()
    avg_dist = np.mean(distances)

    mesh = o3d.geometry.TriangleMesh.create_from_point_cloud_ball_pivoting(
        pcd,
        o3d.utility.DoubleVector([3*avg_dist, 6*avg_dist])
    )

    vertices = np.asarray(mesh.vertices)
    triangles = np.asarray(mesh.triangles)

    fig = go.Figure(data=[
        go.Mesh3d(
            x=vertices[:,0],
            y=vertices[:,1],
            z=vertices[:,2],
            i=triangles[:,0],
            j=triangles[:,1],
            k=triangles[:,2],
            opacity=0.8
        )
    ])

    fig.show()

    return f"Mesh reconstructed and visualized for {plant_name}"

In [ ]:
tools = {
    "dataset_stats": dataset_stats,
    "compute_height": compute_height,
    "voxelize_plant": voxelize_plant,
    "build_graph": build_graph,
    "reconstruct_mesh": reconstruct_mesh
}

In [ ]:
SYSTEM_PROMPT = """
You are a ReAct agent analyzing a maize plant dataset.

Available tools:

dataset_stats
compute_height
voxelize_plant
build_graph
reconstruct_mesh

Use this format:

Thought: reasoning

Action: tool_name
Action Input: tool_argument

The system will execute the tool and return:

Observation: result

Repeat until done.

Final Answer: answer for the user.

Do not invent Observations.
Do not repeat the same tool multiple times unnecessarily.
"""

# Q&A with extended tools

In [ ]:
react_agent("How tall is 0001.ply?")

Thought: We can use the compute_height tool to determine the height of the plant in the 0001.ply file.

Action: compute_height
Action Input: 0001.ply


Final Answer: The height of the plant in the 0001.ply file is 1.514 meters.


In [ ]:
react_agent("Reconstruct mesh for plant 0001.ply")

Thought: To analyze the structure of the maize plant, I need to create a 3D mesh representation.

Action: reconstruct_mesh
Action Input: 0001.ply




Final Answer: The mesh for the maize plant 0001.ply has been successfully reconstructed.


In [ ]:
react_agent("give me voxelized representation of plant 0001.ply")

Thought: We can use the voxelize_plant tool to generate a voxelized representation of the plant from the input PLY file.

Action: voxelize_plant
Action Input: 0001.ply




Final Answer: The voxelized representation of the plant from the PLY file "0001.ply" has been successfully generated.


In [ ]:
react_agent("Build a graph representation for plant 0001.ply")

Thought: Building a graph representation will help us visualize the connections between different parts of the plant.

Action: build_graph
Action Input: 0001.ply




Final Answer: The graph representation for plant 0001.ply has been successfully built.
